In [38]:
import pandas as pd
import mne
import resampy
import random
import os
import numpy as np
from config import *
import concurrent.futures
from typing import List, Tuple, Any


# dest_base = "/media/dll-1/SSD 4TB/EEG Datasets/experiment/nmt_events_adil/"
# process_all_channels = False
# chunk_size = 400

dest_base = "/media/dll-1/SSD 4TB/EEG Datasets/experiment/nouman_conv_4/"
process_all_channels = False
chunk_size = 800

file_saving_path_abnormal = os.path.join(dest_base,"abnormal_crops/")
file_saving_path_normal = os.path.join(dest_base,"normal_crops/")
meta_file_path = os.path.join(dest_base,"meta_data.csv")


csv_folder_path = "/media/dll-1/SSD 4TB/EEG Datasets/NMT_events/csv/SW & SSW CSV Files/"
edf_folders_path_abnormal = ["/media/dll-1/SSD 4TB/EEG Datasets/NMT_events/edf/Abnormal EDF Files/"]
edf_folders_path_normal = ["/media/dll-1/SSD 4TB/EEG Datasets/NMT_events/edf/Normal EDF Files/"]
labels_csv_path = "/media/dll-1/SSD 4TB/EEG Datasets/NMT_events/updated_labels.csv"


meta_data = []

In [39]:
channels_name = ['FP1', 'FP2', 'F3', 'F4', 'C3', 'C4', 'P3', 'P4', 'O1', 'O2', 'F7', 'F8', 'T3', 'T4', 'T5', 'T6', 'FZ', 'PZ', 'CZ']

preproc_functions = []

years = ['2019', '2020', '2021', '2022']
type = ['abnormal', 'normal']

# Initialize counters and data structures
skipped_files_count = 0
missing_files_count = 0
channel_name_issue_count = 0
add_files_count = 0
channels_abnormality_count = {
    'Fp1': 0, 'Fp2': 0, 'F3': 0, 'F4': 0, 'C3': 0, 'C4': 0, 'P3': 0, 'P4': 0, 'O1': 0, 'O2': 0, 
    'F7': 0, 'F8': 0, 'T3': 0, 'T4': 0, 'T5': 0, 'T6': 0, 'FZ': 0, 'PZ': 0, 'CZ': 0
}
lengths = []        # Store the lengths of data segments
fnumber = 0         # File counter


if not os.path.exists(file_saving_path_abnormal):
    os.makedirs(file_saving_path_abnormal)  # Create the directory
    print(f"Directory '{file_saving_path_abnormal}' created.")
if not os.path.exists(file_saving_path_normal):
    os.makedirs(file_saving_path_normal)  # Create the directory
    print(f"Directory '{file_saving_path_normal}' created.")

# Create or load metadata CSV file
if os.path.exists(meta_file_path):
    meta_data = pd.read_csv(meta_file_path)
else:
    meta_data = pd.DataFrame(columns=["numpy_file", "label", "ab_label"])

pd.set_option('display.max_rows', None)   # Set pandas option to display all rows in the console

Directory '/media/dll-1/SSD 4TB/EEG Datasets/experiment/nouman_conv_4/abnormal_crops/' created.
Directory '/media/dll-1/SSD 4TB/EEG Datasets/experiment/nouman_conv_4/normal_crops/' created.


In [40]:
def cleanLabels(labels):
  label_dict = [['No Comment', 'delete previous', 'nan', 'Normal',"Unknown"],
                ['sharp waves', 'sharp wave', 'generalized sharp waves','generalized sharp waves discharge', 'Sharp Wave'],
                ['delta slow wave','delta waves', 'delta slow waves', 'sharp and delta slow waves', 'sharp and delta waves','sharp and delta wave', 'sharp and slow waves', 
                'sharp and slow wave', 'sharp and slow wave','slowing wave', 'sharp and slow waves','sharp and slow wave','generalized paroxymal delta slow waves',
                'generalized paroxysmal delta slow waves','generalized parosysmal delta slow waves', 'generalized delta slow waves', 'slow waves', 
                'generalized delta slow waves ', 'paroxysmal delta slow waves', ' delta slow waves', 'delta waves', 'paroxysmal generalized delta slow waves', 
                'paroxysmal generalized deta slow waves','Delta ','sharp and delta slow waves', 'delta wave', 'Delta Slow Wave'],
                ['2 hertz slow spike and wave discharge','spike wave','spikes','polypspikes and wave','polyspike and wave','polyspikes and wave', 'generalized paroxysmal spike and wave discharge','generalized paroxymal spike and wave discharge', 'fragmented spike and wave discharge', 'generalized paroxysmal 3 hertz spike and wave discharge', 'generalized paroxysmal  spike and wave discharge', 'generalized spike and wave discharge','generalized spike and wave discharges', 'generalized 4 hertz spike and wave discharge', 'spike and wave', 'spike and wave discharge','Generalized 3 hertz spike and wave', 'generalized 3 hertz spike and wave discharge','generalized 3 hertz spike and wave activity', 'generalized 2 hertz spike and wave discharge','generalized 2 hertz spike and wave','2 hertz spike and wave discharge', 'spike and waves', '3 hertz fragmented spike and wave discharge', 'generalized spike and wave ', 'generalized spike and wave', 'generalized spike and wave activity','spike and wave ', 'polyspikes discharge', 'Generalized  paroxysmal 4 hertz spike and wave discharge', 'generalized 3.5 hertz spike and wave discharge', 'generalized 3 hertz spike and wave discharges', 'generalized 2 hertz spike and wave discharges', '3 hertz spike and wave discharge', ' 3 hertz spike and wave discharge', 'paroxysmal generalized 3.5 spike and wave discharge', 'paroxysmal generalized 3.5 hertz spike and wave discharge', ' spike and wave discharge', 'generalized spike  and wave discharge', 'generalized  3 hertz spike and wave discharge', 'generalized  spike and wave discharge', 'generalized 3 hertz  spike and wave discharge', 'spike an dwave', 'spike', 'Paroxysmal generalized 3 hertz spike and wave discharge', 'paroxysmal generalized spike and wave discharge', 'polyspikes', 'paroxysmal generalized 3 hertz spike and wave discharge', 'generalized polyspike discharge', 'generalized polyspikes discharge', 'paroxysmal generalized 4 hertz spike and wave discharge', 'rolandic spike','rolandic spikes', 'generalized paroxysmal 3.5 spike and wave discharge', 'spike and wave discharge 3 hertz', 'fragemented spike and wave discharge', 'fragmented 3 hertz spike and wave discharge', 'generalized  2 hertz spike and wave discharge', 'generalized 2 hertz  spike and wave discharge', 'parosysmal generalized 3 hertz spike and wave discharge', 'spiek and wave', 'generalized 2.5 hertz spike and wave discharge','polyspikes and wave', 'polyspikes ', 'polyspikes', 'spikes', 'polypspikes and wave', 'spike wave','polyspikes ','Spike and Wave Discharge'],
                ['Beta waves', 'beta waves', 'Beta Wave'],
                ['theta waves', 'Theta Wave'],
                ['triphasic waves', 'Triphasic Wave'],
                ['burst suppression','Burst Suppression'],
                ['low voltage','no waveform', 'Low Voltage']]
  ret = []
  for i in range(len(labels)):
    flag = 0
    for j in range(len(label_dict)):
      for k in range(len(label_dict[j])):
        # print(labels[i])
        if label_dict[j][k].lower().strip() == labels[i].lower().strip():
          labels[i] = label_dict[j][-1]
          ret.append(label_dict[j][-1])
          flag = 1
          break
      if flag == 1:
        break
    if flag == 0:
      print("Not found",labels[i])

  if len(ret) != len(labels):
    print(labels)
    print("Did not catch all labels. Please check")
    return labels
  else:
    return ret

if max_abs_val is not None:
    preproc_functions.append(lambda data, fs:(np.clip(data, -max_abs_val, max_abs_val), fs))
preproc_functions.append(lambda data, fs: (resampy.resample(data, fs,sampling_freq,axis=1,filter='kaiser_fast'),sampling_freq))

# if divisor is not None:
#     preproc_functions.append(lambda data, fs: (data / divisor, fs))

In [41]:
def cleanChannels(channels_in_csv):
    for i in range(len(channels_in_csv)):
        for j in range(len(channels_in_csv[i])):
            if channels_in_csv[i][j] == "Add_lead1":
                channels_in_csv[i][j] = "FZ"
            elif channels_in_csv[i][j] == "Add_lead2":
                channels_in_csv[i][j] = "PZ"
            elif channels_in_csv[i][j] == "Add_lead3":
                channels_in_csv[i][j] = "CZ"
            else:
                channels_in_csv[i][j] = channels_in_csv[i][j].split("-")[0].upper()
    return channels_in_csv



In [42]:
# edf_file_name = "../../datasets/[A] EEG Data Files/Processed (edf)/2019/Abnormal/0000002.edf"
# csv_file_name = "../../datasets/[A] EEG Data Files/Abnormalities Ground Truth (csv)/2019/2.csv"
# findex = 0
# lengths = []
# type, channels_in_csv, beg, end = extractLabels(csv_file_name)
# for i in range(len(type)):
#     for j in range(len(channels_in_csv[i])):        
#         trimmed_raw = trimEdf(edf_file_name, findex, channels_in_csv[i][j],beg[i],end[i],type[i])
#         findex += 1
#         leng = trimmed_raw.shape[0]
#         break

#     lengths.append(leng)
#     break
#         # trimmed_raw.plot(duration=20, n_channels=1)


In [43]:
def convert_to_datetime(dt_str):
    return pd.to_datetime(dt_str, format='%H:%M:%S:%f')


In [44]:
def fix_invalid_timestamp(dt_str):
    if(not dt_str is np.nan):
        dt_strs = str(dt_str).split(":")
        if len(dt_strs) < 4:
            dt_strs.append("000")
        new_dt_str = ":".join(dt_strs)
        hours, minutes, seconds, milliseconds = map(int, new_dt_str.split(':'))

        if seconds >= 60:
            minutes += seconds // 60
            seconds %= 60
        if minutes >= 60:
            hours += minutes // 60
            minutes %= 60

        return f'{hours:02d}:{minutes:02d}:{seconds:02d}:{milliseconds:03d}'
    else:
        return dt_str


In [45]:
def extractLabels(csv_file):
    # Read the CSV file into a DataFrame
    csv = pd.read_csv(csv_file)
    # Check if the column 'File Start' exists in the CSV
    if 'File Start' in csv.columns:
        # Read the CSV file again (unnecessary, could use the already loaded `csv` DataFrame)
        df = pd.read_csv(csv_file)

        # Extract the 'Comment' column and clean it using the cleanLabels function
        type = csv['Comment'].to_numpy()
        type = cleanLabels(type)

        # Extract and split 'Channel names' column, then clean it using the cleanChannels function
        channels = csv['Channel names'].str.split().to_numpy()
        channels = cleanChannels(channels)

        # Fix invalid timestamps in 'Start time', 'End time', and 'File Start', then convert to datetime
        csv['Start time'] = csv['Start time'].apply(fix_invalid_timestamp).apply(convert_to_datetime)
        csv['End time'] = csv['End time'].apply(fix_invalid_timestamp).apply(convert_to_datetime)
        csv['File Start'] = csv['File Start'].apply(fix_invalid_timestamp).apply(convert_to_datetime)

        # Normalize 'Start time' relative to the first 'File Start' and convert to seconds
        csv['Start time'] = ((csv['Start time'] - csv['File Start'][0]).dt.total_seconds())

        # Adjust 'Start time' if it exceeds 1 hour (3600 seconds)
        result = csv[csv['Start time'] > 60 * 60]
        csv.loc[result.index, 'Start time'] -= 3600

        # Scale 'Start time' by 200 and convert to integer
        csv['Start time'] = (csv['Start time'] * 200).astype(int)

        # Normalize 'End time' relative to the first 'File Start' and convert to seconds
        csv['End time'] = ((csv['End time'] - csv['File Start'][0]).dt.total_seconds())

        # Adjust 'End time' if it exceeds 1 hour (3600 seconds)
        result = csv[csv['End time'] > 60 * 60]
        csv.loc[result.index, 'End time'] -= 3600

        # Scale 'End time' by 200 and convert to integer
        csv['End time'] = (csv['End time'] * 200).astype(int)

        # Check for rows where 'End time' is less than 'Start time'
        res = csv[csv['End time'] - csv['Start time'] < 0]

        # If no invalid rows, return the processed data as numpy arrays
        if res.empty:
            return np.array(type), np.array(channels), np.array(csv['Start time']), np.array(csv['End time'])
        else:
            # Print the invalid rows for debugging purposes
            print(df[csv['End time'] - csv['Start time'] < 0])
    else:
        # If 'File Start' column is missing, count this file as skipped
        global skipped_files_count
        skipped_files_count += 1

        # Return empty arrays for consistency
        return [], [], [], []


In [46]:
def fix_channels(raw):
    # Get all channel names from the file
    all_channels = raw.ch_names
    # List of channels to drop
    channels_to_drop = ['A1', 'A2', 'ECG']

    # Check if the channels to drop exist in the file
    existing_channels = [ch for ch in channels_to_drop if ch in all_channels]

    # Drop only the existing channels
    if existing_channels:
        raw.drop_channels(existing_channels)

    # Step 2: Compute the average channel
    # Extract data as a numpy array (n_channels, n_samples)
    data, times = raw.get_data(return_times=True)
    average_channel = np.mean(data, axis=0, keepdims=True)

    # Step 3: Add the average channel
    # Define the new channel name and its info
    average_channel_name = 'Avg'
    info = mne.create_info([average_channel_name], sfreq=raw.info['sfreq'], ch_types='eeg',verbose=False)

    # Create a new Raw object for the average channel
    average_raw = mne.io.RawArray(average_channel, info,verbose=False)

    # Append the average channel to the original data
    raw.add_channels([average_raw])
    return raw

In [47]:
def trimEdf(raw, fname, findex, channel_name, start_idx, end_idx, type):
    # Load the EDF file
    data = []
    
    if process_all_channels:
        channel_data = raw.get_data()  # Shape: (num_channels, total_samples)

        # times = raw.times  # Corresponding time array
    else:
        # Extract the data for the specified channel
        channel_data, times = raw[channel_name, :]
    
    current_chunk_length = end_idx - start_idx
    # print(channel_data.shape[1], end_idx)
    if channel_data.shape[1]  < end_idx or channel_data.shape[1]  < start_idx:
        return []
    

    # # Adjust indices for chunks smaller than chunk_size
    # if current_chunk_length < chunk_size:
    #     padding = (chunk_size - current_chunk_length) // 2
    #     start_idx = max(start_idx - padding, 0)
    #     end_idx = min(end_idx + padding, len(channel_data[0]))

    # Process chunks larger than chunk_size
    if current_chunk_length > chunk_size:
        overlap = chunk_size // 4  # 25% overlap
        current_start = start_idx

        # Create chunks with overlap
        while current_start + chunk_size <= end_idx:
            process_and_save_chunk(
                raw, channel_data, current_start, current_start + chunk_size,
                fname, findex, channel_name, type
            )
            findex += 1
            current_start += chunk_size - overlap

        # Handle the last chunk if it does not align perfectly
        if current_start < end_idx:
            processed_chunk = process_and_save_chunk(raw, channel_data, current_start, end_idx, fname, findex, channel_name, type)
            if processed_chunk != []: 
                data.append(processed_chunk)

    # Process and save a single chunk if valid
    elif current_chunk_length > 0:
        data.append(process_and_save_chunk(raw, channel_data, start_idx, end_idx, fname, findex, channel_name, type)
            )
    return data


def process_and_save_chunk(raw, channel_data, start_idx, end_idx, fname, findex, channel_name, type):
    # Adjust for small chunks
    # Check if the current chunk length is smaller than the desired chunk size
    lpad = 0
    rpad = 0
    if end_idx - start_idx < chunk_size:
        # Calculate the padding needed to reach the desired chunk size
        padding = (chunk_size - (end_idx - start_idx)) // 2

        # Adjust left padding if start index goes below 0
        if start_idx - padding < 0:
            lpad = abs(padding - start_idx)

        # Adjust right padding if end index exceeds channel data length
        if end_idx + padding > len(channel_data[0]):
            rpad = abs(end_idx - padding)

        # Update start and end indices with padding adjustments
        start_idx = max((start_idx - padding), 0) + rpad
        end_idx = min((end_idx + padding), len(channel_data[0])) + lpad
    
    # Handle edge cases where the chunk length is less than 600 samples
    # Ensure the updated indices are valid
    if end_idx - start_idx > 0:
        if  end_idx - start_idx < chunk_size:
                if start_idx != 0:
                    start_idx -= 1
                else:
                    end_idx += 1
        # Extract and scale the data
        
        data = (channel_data[:, int(start_idx):int(end_idx)] * 1e6).astype(np.float32)

        fs = raw.info['sfreq']

        # Apply preprocessing functions
        for fn in preproc_functions:
            data, fs = fn(data, fs)

        # Save the processed data
        if process_all_channels:
            channel_name = raw.info['ch_names']
            if(data.shape[0]!=len(channels_name)+1):
                print("Number of Channels not accurate", data.shape[0])
                return []
            np_file_saving_path = f"{os.path.splitext(os.path.basename(fname))[0]}_{findex}_{label_dict.index('abnormal')}_{ab_label_dict.index(type)}.npz"
            
        else:
            if(data.shape[0]!=1):
                print("Number of Channels not accurate", data.shape[0])
                return []
            np_file_saving_path = f"{os.path.splitext(os.path.basename(fname))[0]}_{findex}_{label_dict.index('abnormal')}_{channel_name}_{ab_label_dict.index(type)}.npz"

        if(data.shape[1]!=chunk_size):
            print("Chunk size not accurate", end_idx,start_idx,end_idx - start_idx)
            return []

        np.savez(
            file_saving_path_abnormal + np_file_saving_path,
            data=data,
            label=label_dict.index("abnormal"),
            ab_label=ab_label_dict.index(type),
            beg=start_idx,
            end=end_idx,
            frequency=fs,
            channel=channel_name
        )
        return [data, np_file_saving_path,label_dict.index("abnormal"),ab_label_dict.index(type)]
    else:
        return []


In [48]:
def getNormalChunk(raw, fname, channel_name, beg, end, type, num_chunks, findex):
    # Get the total duration of the recording in seconds
    duration = raw.times[-1]

    # Initialize an array to store randomly generated time points, excluding specified intervals
    random_time_points = []
    count_to_break_loop = 0
    processed_data_to_return = []

    # Generate random time points ensuring they don't overlap with excluded intervals
    while len(random_time_points) < num_chunks:
        count_to_break_loop += 1

        # Generate a random candidate time point, avoiding the edges of the recording
        candidate_time_point = int(np.random.uniform(60, duration - chunk_size / 200 - 60)) * 200

        # Check if the candidate time point is outside all excluded intervals
        if not any((b <= candidate_time_point < e) or (b < candidate_time_point + chunk_size <= e) for b, e in zip(beg, end)):
            count_to_break_loop -= 1
            random_time_points.append(candidate_time_point)

        # Break the loop if too many attempts fail to find a valid chunk
        if len(random_time_points) == 0 and count_to_break_loop == num_chunks * 100:
            print("Can't find Normal chunk")
            break
    # print(random_time_points)

    # Extract data chunks for each valid random time point
    for time_point in random_time_points:
        start_idx = time_point
        end_idx = time_point + chunk_size

        # If no channel name is provided, select one randomly from available channels
        if channel_name == '':
            channel_name = random.choice(channels_name)

        # Extract data for the specified channel
        if process_all_channels:
            channel_data = raw.get_data()
            channel_name = raw.info['ch_names']

        channel_data, times = raw[channel_name, :]

        # Ensure valid chunk length
        if end_idx - start_idx > 0:
            if end_idx - start_idx < chunk_size:
                if start_idx != 0:
                    start_idx -= 1
                else:
                    end_idx += 1

            # Extract and scale the data to microvolts
            data = (channel_data[:, start_idx:end_idx] * 1e6).astype(np.float32)

            # Get the sampling frequency
            fs = raw.info['sfreq']

            # Apply preprocessing functions if data length is sufficient
            if not len(data[0]) < 200:
                for fn in preproc_functions:
                    data, fs = fn(data, fs)
                    data = data.astype(np.float32)
                    fs = float(fs)

                # Append the start and end indices to the exclusion intervals
                np.append(beg, start_idx)
                np.append(end, end_idx)

                # Save the processed chunk and metadata to a .npz file


                if process_all_channels:
                    if(data.shape[0]!=len(channels_name)+1):
                        print("Number of Channels not accurate", data.shape[0])
                        continue
                    np_file_saving_path = os.path.splitext(os.path.basename(fname))[0] + "_" + str(findex) + "_" + str(label_dict.index("normal")) + "_" + str(ab_label_dict.index(type)) + ".npz"
                else:
                    if(data.shape[0]!=1):
                        print("Number of Channels not accurate", data.shape[0])
                        continue
                    np_file_saving_path = os.path.splitext(os.path.basename(fname))[0] + "_" + str(findex) + "_" + str(label_dict.index("normal")) + "_" + str(channel_name) + "_" + str(ab_label_dict.index(type)) + ".npz"
                
                if(data.shape[1]!=chunk_size):
                    print("Chunk size not accurate", end_idx,start_idx,end_idx - start_idx)
                else:
                    np.savez(
                        file_saving_path_normal + np_file_saving_path,
                        data=data,
                        label=label_dict.index("normal"),
                        ab_label=ab_label_dict.index(type),
                        beg=start_idx,
                        end=end_idx,
                        frequency=sampling_freq,
                        channel=channel_name
                    )

                    # Increment the file index
                    findex += 1
                    
                    processed_data_to_return.append([data, np_file_saving_path,label_dict.index("normal"),ab_label_dict.index(type)])

    # Return the updated exclusion intervals
    return beg, end, processed_data_to_return


In [49]:
def save_in_meta_file(trimmed_raws, findex):
    # If trimmed data is not empty, process and save it
    new_rows = []
    if len(trimmed_raws) != 0:
        for trimmed_chunk in trimmed_raws:
                                    # Save metadata for each chunk
            if(trimmed_chunk != []):
                new_rows.append({
                                            "numpy_file": trimmed_chunk[1],
                                            "label": trimmed_chunk[2],
                                            "ab_label": trimmed_chunk[3],
                    })
                # print(trimmed_chunk[0].shape)  # Get the length of the trimmed data
                findex += 1
    return  new_rows, findex


In [50]:
def process_abnormal_file(params: Tuple[str, str, str, str, Any]) -> Tuple[List[dict], List[str], List[str], int]:
    """
    Process a single abnormal EDF file.

    Args:
        params: A tuple containing necessary parameters:
            - edf_folder_path: Path to the EDF folder
            - file_name: Name of the EDF file
            - csv_folder_path: Path to the corresponding CSV folder
            - meta_data_subset: A subset of meta_data relevant for this file
            - global_findex: Starting index for this file

    Returns:
        A tuple containing:
            - new_rows: List of new metadata rows to append
            - errored_files_start_time: List containing the CSV file path if an error occurred
            - errored_files_annotation_length: List containing the CSV file path if an error occurred
            - updated_findex: The updated findex after processing
    """
    edf_folder_path, file_name, csv_folder_path, meta_data, global_findex = params
    new_rows = []
    errored_files_start_time = []
    errored_files_annotation_length = []
    findex = global_findex

    edf_file_path = os.path.join(edf_folder_path, file_name)
    base_name = file_name.split("_")

    csv_file_name = f"{os.path.splitext(base_name[0])[0].lstrip('0')}.csv"
    csv_file_path = os.path.join(csv_folder_path, csv_file_name)

    # Check if EDF file is not a directory and CSV exists
    if not os.path.isdir(edf_file_path) and os.path.isfile(csv_file_path):
        try:
            # Increment file index
            findex += 1

            # Extract labels from CSV
            type_labels, channels_in_csv, beg, end = extractLabels(csv_file_path)

            # Determine total possible chunks
            total_chunks_possible = len(type_labels) if process_all_channels else sum(len(ch) for ch in channels_in_csv)
            # Handle error if total_chunks_possible is zero
            if total_chunks_possible == 0:
                errored_files_start_time.append(csv_file_path)
                print("processing",global_findex,file_name,"---------------Skipped Errored")
                return new_rows, errored_files_start_time, errored_files_annotation_length, findex

            # Check existing chunks in meta_data
            # existing_chunks = meta_data[meta_data['numpy_file'].str.contains(f"{base_name[0].replace('.edf', '')}")]
            # if len(existing_chunks) >= total_chunks_possible * (3/4):
            #     # Considered as already sufficiently processed
            #     print("processing",global_findex,file_name,"-------------------Skipped Already Processed")

            #     return new_rows, errored_files_start_time, errored_files_annotation_length, findex

            print("processing",global_findex,file_name)
           # Read EDF file
            raw = mne.io.read_raw_edf(edf_file_path, preload=True, verbose=False)

            # Check annotation length
            if raw.n_times < max(end):
                # print("processing",global_findex,file_name,"-------------------Skipped Already Processed")
                errored_files_annotation_length.append(csv_file_path)
                # Continue processing even if there's an annotation length error
                # Depending on your requirement, you might want to skip
                # return new_rows, errored_files_start_time, errored_files_annotation_length, findex

            # Initialize exclusion lists
            exclude_beg = beg.copy()
            exclude_end = end.copy()

            if process_all_channels:
                raw = fix_channels(raw)

            # Process each type label
            for i in range(len(type_labels)):
                # Generate normal chunks
                exclude_beg, exclude_end, trimmed_raws = getNormalChunk(
                    raw,
                    edf_file_path,
                    random.choice(channels_in_csv[i]),
                    exclude_beg,
                    exclude_end,
                    "Normal",
                    0,
                    findex
                )

                # Check trimmed chunks
                for trimmed_chunk in trimmed_raws:
                    if trimmed_chunk != [] and trimmed_chunk[0].shape[1] != chunk_size:
                        print("-------------error--------", edf_file_path)

                # Save to metadata
                rows, findex = save_in_meta_file(trimmed_raws, findex)
                new_rows.extend(rows)

                if process_all_channels:
                    trimmed_raws = trimEdf(
                        raw, edf_file_path, findex, False, beg[i], end[i], type_labels[i]
                    )
                    for trimmed_chunk in trimmed_raws:
                        if trimmed_chunk != [] and trimmed_chunk[0].shape[1] != chunk_size:
                            print("-------------error--------", edf_file_path)

                    rows, findex = save_in_meta_file(trimmed_raws, findex)
                    new_rows.extend(rows)
                else:
                    # Process each channel for the current type
                    for j in range(len(channels_in_csv[i])):
                        trimmed_raws = trimEdf(
                            raw, edf_file_path, findex, channels_in_csv[i][j], beg[i], end[i], type_labels[i]
                        )
                        for trimmed_chunk in trimmed_raws:
                            if trimmed_chunk != [] and trimmed_chunk[0].shape[1] != chunk_size:
                                print("-------------error--------", edf_file_path)

                        rows, findex = save_in_meta_file(trimmed_raws, findex)
                        new_rows.extend(rows)

            return new_rows, errored_files_start_time, errored_files_annotation_length, findex

        except Exception as e:
            print(f"Exception processing file {edf_file_path}: {e}")
            # You can choose to log this exception as needed
            return new_rows, errored_files_start_time, errored_files_annotation_length, findex
    else:
        # Handle missing CSV files
        if not os.path.isfile(csv_file_path):
            # Indicate missing CSV; this can be handled separately
            # You may choose to log it or return a specific flag
            # For simplicity, we'll skip and return empty
            return new_rows, errored_files_start_time, errored_files_annotation_length, findex
        else:
            # If EDF is a directory, skip
            return new_rows, errored_files_start_time, errored_files_annotation_length, findex


In [51]:
def extract_from_abnormal_files():
    if os.path.isfile(meta_file_path):
        meta_data = pd.read_csv(meta_file_path)
    else:
        meta_data = pd.DataFrame(columns=['numpy_file', 'label', 'ab_label'])

    # Initialize counters and error logs
    missing_files_count = 0
    total_findex = 0  # Initialize global findex

    all_new_rows = []
    all_errored_start = []
    all_errored_annotation = []

    # Iterate over EDF folders
    for edf_folder_path in edf_folders_path_abnormal:
        for file_name in os.listdir(edf_folder_path):
            edf_file_path = os.path.join(edf_folder_path, file_name)

            # Skip directories
            if os.path.isdir(edf_file_path):
                continue

            # Append to tasks with initial findex
            total_findex += 1
            task = (
                edf_folder_path,
                file_name,
                csv_folder_path,
                meta_data.copy(),  # Pass a copy to prevent modifying the original DataFrame
                total_findex  # Initial findex; will be updated in function
            )

            try:
                # Process file sequentially (no parallel execution)
                new_rows, errored_start, errored_annotation, updated_findex = process_abnormal_file(task)

                # Collect results
                all_new_rows.extend(new_rows)
                all_errored_start.extend(errored_start)
                all_errored_annotation.extend(errored_annotation)
                total_findex = max(total_findex, updated_findex)

            except Exception as exc:
                print(f"Error processing {file_name}: {exc}")

    # Update metadata with new rows
    if all_new_rows:
        meta_data = pd.concat([meta_data, pd.DataFrame(all_new_rows)], ignore_index=True)
        meta_data.to_csv(meta_file_path, index=False)
        print(f"Metadata updated. {len(all_new_rows)} new rows added.")
    else:
        print("No new rows to add to metadata.")

    # Save error logs
    if all_errored_start:
        df_error_start_time = pd.DataFrame(all_errored_start, columns=["file_name"])
        df_error_start_time.to_csv("error_start_time.csv", index=False)
        print(f"{len(all_errored_start)} files had start time errors.")

    if all_errored_annotation:
        df_error_annotation_length = pd.DataFrame(all_errored_annotation, columns=["file_name"])
        df_error_annotation_length.to_csv("error_annotation_length.csv", index=False)
        print(f"{len(all_errored_annotation)} files had annotation length errors.")

    print(f"Processing complete. Final findex: {total_findex}")
    print(f"Total missing files: {missing_files_count}")


In [52]:
def process_normal_file(params):
    """
    This function executes in a parallel worker. 
    We keep it self-contained: it does not modify global variables.
    Returns rows to append to meta_data (or an empty list if none).
    """
    (
        edf_file_path,         # full path to .edf file
        file_name,             # just the base name
        process_all_channels,
        channels_name,
        findex
    ) = params

    # Local lists (independent for each file)
    exclude_in_normal_beg = []
    exclude_in_normal_end = []

    # Load raw data
    raw = mne.io.read_raw_edf(edf_file_path, preload=True, verbose=False)
    
    # Potentially fix channels
    if process_all_channels:
        raw = fix_channels(raw)

    # Generate normal chunks
    exclude_in_normal_beg, exclude_in_normal_end, trimmed_raws = getNormalChunk(
        raw,
        edf_file_path,
        random.choice(channels_name),
        exclude_in_normal_beg,
        exclude_in_normal_end,
        "Normal",
        200,
        0
    )

    # Check shape
    for trimmed_chunk in trimmed_raws:
        if trimmed_chunk != []:
            # Suppose we expect exactly 600 samples in length
            if trimmed_chunk[0].shape[1] != chunk_size:
                print("-------------error--------", trimmed_chunk)
                # handle error

    # Save new rows to meta file structure
    new_rows, findexx = save_in_meta_file(trimmed_raws, findex)

    return new_rows


# ----------------------------------------------------
# Main function orchestrating parallel processing
# ----------------------------------------------------


In [53]:
def extract_from_normal_files():
    if os.path.isfile(meta_file_path):
        meta_data = pd.read_csv(meta_file_path)
    else:
        meta_data = pd.DataFrame(columns=['numpy_file', 'label', 'ab_label'])

    # ------------------------------------------------
    # Build a list of (unprocessed) files to process
    # ------------------------------------------------
    tasks = []
    findex = 0

    for edf_folder_path in edf_folders_path_normal:
        for file_name in os.listdir(edf_folder_path):
            edf_file_path = os.path.join(edf_folder_path, file_name)

            # Skip directories
            if os.path.isdir(edf_file_path):
                continue

            # Check if file is already processed in meta_data
            if meta_data[meta_data['numpy_file'].str.contains(file_name.replace(".edf", ""))].shape[0] > 0:
                print("Already Processed:", file_name)
                continue

            # If not processed, add to the tasks list
            findex += 1
            print("Processing:", findex, file_name)

            task = (
                edf_file_path,
                file_name,
                process_all_channels,
                channels_name,
                findex
            )

            # ------------------------------------------------
            # Process file sequentially (no parallel execution)
            # ------------------------------------------------
            try:
                new_rows = process_normal_file(task)

                # Collect results
                if new_rows:
                    tasks.extend(new_rows)

            except Exception as e:
                print(f"Error processing {file_name}: {e}")

    # ------------------------------------------------
    # Update meta_data with all new rows
    # ------------------------------------------------
    if tasks:
        meta_data = pd.concat([meta_data, pd.DataFrame(tasks)], ignore_index=True)
        meta_data.to_csv(meta_file_path, index=False)
        print(f"Metadata updated. {len(tasks)} new rows added.")
    else:
        print("No new rows to add to metadata. All files were already processed.")

    print("Done.")


In [54]:
extract_from_abnormal_files()
extract_from_normal_files()


processing 1 0000964.edf


processing 6626 0000873.edf
processing 6950 0000634.edf
processing 7204 0000586.edf
processing 7895 0000585.edf
processing 8036 0000926.edf
processing 8100 0000138.edf
processing 8977 0000940.edf
processing 9036 0000006.edf
processing 9265 0000952.edf
processing 11053 0000337.edf
processing 13755 0000734.edf
processing 13930 0000893.edf
processing 19786 0000577.edf
processing 22677 0000765.edf
processing 24097 0001072.edf
processing 24128 0000353.edf
processing 24384 0001065.edf
processing 24579 0000245.edf
processing 24619 0000266.edf
processing 25837 0001082.edf
processing 25981 0000472.edf
processing 26021 0000391.edf
processing 27114 0000908.edf
processing 27215 0001090.edf
processing 27949 0000437.edf
processing 34621 0000638.edf
processing 35066 0000507.edf
processing 36754 0000637.edf
processing 36877 0000359.edf
processing 36973 0000243.edf
processing 37013 0000494.edf
processing 37478 0000502.edf
processing 37637 0000965.edf
processing 37658 0000131.edf
processing 37760 000037

In [55]:
import os
import shutil
import pandas as pd
import re

# Paths to source folders
normal_source = file_saving_path_normal
abnormal_source = file_saving_path_abnormal

# Paths to destination folders
train_dest = os.path.join(dest_base, "train")
eval_dest = os.path.join(dest_base, "eval")
test_dest = os.path.join(dest_base, "test")

# Ensure destination folders exist
for folder in [train_dest, eval_dest, test_dest]:
    os.makedirs(folder, exist_ok=True)

# Load the CSV file
df = pd.read_csv(labels_csv_path)

# Function to find matching files in both normal and abnormal folders
def find_matching_files(base_filename, source_folder):
    """Finds all matching files in the source folder using split logic."""
    matching_files = []
    for file in os.listdir(source_folder):
        parts = file.split("_")  # Splitting filename by '_'

        if parts[0] == base_filename and file.endswith(".npz"):
            matching_files.append(os.path.join(source_folder, file))

    return matching_files

# Iterate over each row in the CSV
for index, row in df.iterrows():
        edf_filename = row["recordname"]  # "filename.edf"
        base_filename = os.path.splitext(edf_filename)[0]  # Extract "filename"
        label = row["label"]  # 0 = Normal, 1 = Abnormal
        folder_name = row["loc"]  # train, eval, test
    # if(edf_filename == "0000085.edf"):
        # Search for matching files in both normal and abnormal folders
        normal_matches = find_matching_files(base_filename, normal_source)
        abnormal_matches = find_matching_files(base_filename, abnormal_source)
        # print(normal_matches)
        # Combine results from both folders
        # print(abnormal_matches)
        all_matches = normal_matches + abnormal_matches
        # print(all_matches)
        if not all_matches:
            print(f"No matching files found for: {edf_filename}, {row['age']} , {row['label']}")
            continue
        # Determine the destination folder
        if folder_name == "train":
            dest_folder = train_dest
        elif folder_name == "valid":
            dest_folder = eval_dest
        elif folder_name == "test":
            dest_folder = test_dest
        else:
            print(f"Skipping {edf_filename}: Unknown folder name {folder_name}")
            continue

        # Copy all matching files to the destination
        # print(index, "Copying:",len(all_matches),"of ",base_filename,"to ",dest_folder)

        for src_file in all_matches:
            dest_file = os.path.join(dest_folder, os.path.basename(src_file))
            shutil.copy(src_file, dest_file)
            # print(f"Copied {len(src_file)} -> {dest_folder}")

print("File transfer complete.")


No matching files found for: 0000085.edf, 79.0 , normal


No matching files found for: 0000077.edf, 70.0 , normal
No matching files found for: 0000063.edf, 62.0 , normal
No matching files found for: 0000070.edf, 62.0 , normal
No matching files found for: 0000068.edf, 59.0 , normal
No matching files found for: 0000067.edf, 59.0 , normal
No matching files found for: 0000040.edf, 49.0 , normal
No matching files found for: 0000071.edf, 43.0 , normal
No matching files found for: 0000074.edf, 43.0 , normal
No matching files found for: 0000097.edf, 39.0 , normal
No matching files found for: 0000065.edf, 38.0 , normal
No matching files found for: 0000084.edf, 35.0 , normal
No matching files found for: 0000048.edf, 32.0 , normal
No matching files found for: 0000099.edf, 31.0 , normal
No matching files found for: 0000078.edf, 31.0 , normal
No matching files found for: 0000044.edf, 30.0 , normal
No matching files found for: 0000089.edf, 28.0 , normal
No matching files found for: 0000061.edf, 27.0 , normal
No matching files found for: 0000082.edf, 27.0 ,

In [56]:
import os
import pandas as pd

# Folders to process
folders = ['train', 'eval', 'test']

for folder in folders:
    folder_path = os.path.join(dest_base, folder)
    records = []

    for file in os.listdir(folder_path):
        if file.endswith('.npz'):
            print(file)
            filename_no_ext = file[:-4]
            parts = filename_no_ext.split('_')
            
            if len(parts) != 5:
                print(f"Skipping malformed filename: {file}")
                continue

            filename, chunknumber, label, channel_name, abnormality_type = parts
            print(abnormality_type)
            if(abnormality_type == "0"):
                abnormality_type_3_class = 0
            elif(abnormality_type == "1" or abnormality_type == "3"):
                abnormality_type_3_class = 1
            else:
                abnormality_type_3_class = 2

            ab_label_dict = ['Normal','Sharp Wave','Delta Slow Wave', 'Spike and Wave Discharge', 'Beta Wave', 'Theta Wave', 'Triphasic Wave', 'Low Voltage','Burst Suppression','Unknown']

            records.append({
                'file_name': os.path.join(folder_path,file),
                'label': label,
                'channel_name': channel_name,
                'abnormality_type': abnormality_type,
                'abnormality_type_3_class': abnormality_type_3_class
            })

    df = pd.DataFrame(records)
    csv_path = os.path.join(dest_base, f"{folder}.csv")
    df.to_csv(csv_path, index=False)
    print(f"✅ Saved {csv_path} with {len(df)} entries.")


0000281_49462_1_C3_2.npz
2
0000980_152_0_FZ_0.npz
0
0000873_6872_1_P4_3.npz
3
0000541_111_0_FP1_0.npz
0
0000293_38_0_CZ_0.npz
0
0000437_28627_1_F7_2.npz
2
0000536_60_0_T3_0.npz
0
0000803_162_0_F7_0.npz
0
0001086_48386_1_FP2_2.npz
2
0001022_110076_1_F7_3.npz
3
0000884_79251_1_C3_3.npz
3
0000561_6_0_F3_0.npz
0
0000259_98_0_O1_0.npz
0
0000772_86_0_T4_0.npz
0
0000127_53273_1_C4_2.npz
2
0000494_37368_1_C4_3.npz
3
0000103_57986_1_T6_2.npz
2
0000700_100135_1_FP1_3.npz
3
0000445_133_0_FZ_0.npz
0
0000692_115_0_FP1_0.npz
0
0000629_84_0_P3_0.npz
0
0000202_91_0_F4_0.npz
0
0000300_0_0_FP2_0.npz
0
0000899_160_0_P4_0.npz
0
0001022_107080_1_PZ_2.npz
2
0000538_88024_1_PZ_3.npz
3
0000331_101_0_FP2_0.npz
0
0001022_113471_1_F3_2.npz
2
0000538_88002_1_T5_3.npz
3
0000028_77_0_T3_0.npz
0
0000232_149_0_T5_0.npz
0
0000169_177_0_F7_0.npz
0
0000127_50925_1_T4_2.npz
2
0000214_7_0_F7_0.npz
0
0000764_68412_1_P3_2.npz
2
0000386_93112_1_P3_3.npz
3
0000242_5_0_F8_0.npz
0
0000340_69_0_P3_0.npz
0
0000383_42_0_FP1_0.npz


✅ Saved /media/dll-1/SSD 4TB/EEG Datasets/experiment/nouman_conv_4/train.csv with 210211 entries.
0000645_67_0_FP1_0.npz
0
0000805_28_0_C3_0.npz
0
0000828_91675_1_O2_1.npz
1
0000510_113840_1_C4_2.npz
2
0000828_92680_1_O1_1.npz
1
0000360_107_0_P3_0.npz
0
0000753_40511_1_F3_2.npz
2
0001069_183_0_P4_0.npz
0
0000137_44394_1_F4_2.npz
2
0000668_126_0_O1_0.npz
0
0000964_3302_1_F4_3.npz
3
0001077_62_0_CZ_0.npz
0
0000643_40_0_PZ_0.npz
0
0000964_749_1_F3_3.npz
3
0000809_149_0_O1_0.npz
0
0000222_43739_1_F7_3.npz
3
0000305_60_0_FP1_0.npz
0
0000696_75_0_T3_0.npz
0
0000689_92_0_F8_0.npz
0
0001035_7_0_O2_0.npz
0
0000801_199_0_O1_0.npz
0
0000964_3771_1_P3_3.npz
3
0000217_84709_1_T3_3.npz
3
0000828_92786_1_P4_1.npz
1
0000753_40995_1_T5_3.npz
3
0001069_94_0_P4_0.npz
0
0000316_144_0_PZ_0.npz
0
0000835_82_0_PZ_0.npz
0
0000945_97_0_F7_0.npz
0
0000864_40347_1_FP1_3.npz
3
0000882_61_0_P3_0.npz
0
0000863_172_0_T6_0.npz
0
0000814_39_0_P3_0.npz
0
0000828_92165_1_P4_1.npz
1
0000863_94_0_T6_0.npz
0
0001077_30_0_C

In [57]:
# Testing or validating the data wiith plots

import matplotlib.pyplot as plt

file_path = "/media/dll-1/SSD 4TB/EEG Datasets/EEG_crops/abnormal_crops/2019_0001607_1_1_False_2.npz"

# file_path = "../../datasets/A_EEG_Data_Files/Processed_New/Abnormality_Crops/2020_0000004_0_1_C3_1.npz"

# Load data from the .npz file
loaded_data = np.load(file_path)

# Access individual arrays by their keys
data = loaded_data['data']
print(data[0])

x = np.arange(loaded_data['beg'],loaded_data['end'])
print(len(data))
# Plot the data
plt.plot(x, data)
plt.xlabel('Index')
plt.ylabel('Values')
plt.title('Plot of channel '+str(loaded_data['channel'])+' '+str(loaded_data['ab_label']))
plt.show()


root_folder = "../../datasets/A_EEG_Data_Files/Processed_New/Abnormality_Crops/"
abnormal_files = os.listdir(root_folder)
for file_path in abnormal_files:
    loaded_data = np.load(root_folder+file_path)
    print(len(loaded_data['data'][0]))
#     if(len(loaded_data['data'][0]) == 0):
#          os.remove(root_folder+file_path)
    

FileNotFoundError: [Errno 2] No such file or directory: '/media/dll-1/SSD 4TB/EEG Datasets/EEG_crops/abnormal_crops/2019_0001607_1_1_False_2.npz'